# Postcards from My Jungle — sound generation

Uses the pre-trained **Stable Audio Open 1.0** text-to-audio diffusion model to make one call for each of the 16 creature clans, each a different length (2–20 s).

**Before running:**
1. **Runtime → Change runtime type → T4 GPU.**
2. Accept the model licence at https://huggingface.co/stabilityai/stable-audio-open-1.0 (you must be logged in to Hugging Face).
3. Create a read token at https://huggingface.co/settings/tokens — the login cell asks for it.

Output: `sounds/sound_01.mp3` … `sound_16.mp3`, the filenames the website expects. Sound *k* belongs to phrase *k* in `language/phrases.json`.

In [1]:
!pip install -q -U diffusers transformers accelerate soundfile torchsde

In [4]:
from huggingface_hub import notebook_login
notebook_login()

In [15]:
import os, subprocess, zipfile
import numpy as np
import torch
import soundfile as sf
from IPython.display import Audio, display
from diffusers import StableAudioPipeline
from huggingface_hub import get_token

# Retrieve token programmatically to ensure it is passed correctly
hf_token = get_token()
if hf_token is None:
    print("WARNING: No Hugging Face token detected. Please run the notebook_login() cell above first.")
else:
    print("Hugging Face token detected successfully.")

pipe = StableAudioPipeline.from_pretrained(
    "stabilityai/stable-audio-open-1.0",
    torch_dtype=torch.float16,
    token=hf_token if hf_token else True
).to("cuda")

SR = pipe.vae.sampling_rate
print("sample rate:", SR)

Hugging Face token detected successfully.


/usr/local/lib/python3.13/dist-packages/diffusers/utils/deprecation_utils.py:23: FutureWarning: `torch_dtype` is deprecated and will be removed in version 1.0.0. Please use `dtype` instead.
  deprecate("torch_dtype", "1.0.0", _TORCH_DTYPE_DEPRECATION_MESSAGE)


Loading pipeline components...:   0%|          | 0/6 [00:00<?, ?it/s]

/usr/local/lib/python3.13/dist-packages/torch/nn/utils/weight_norm.py:144: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  WeightNorm.apply(module, name, dim)


Loading weights:   0%|          | 0/99 [00:00<?, ?it/s]

sample rate: 44100


## Prompts

Each prompt describes **body size + type of sound + habitat + mood**, ending with recording cues ("field recording", "close microphone") that push the model towards natural sounds instead of music. Durations match the `seconds` values in `index.html`.

In [16]:
SOUNDS = [
    {"clan": "Kithuru", "seconds": 3, "prompt": "a small lizard-like tree creature making dry clicking croaks among rustling leaves, nature field recording, close microphone"},
    {"clan": "Vashari", "seconds": 6, "prompt": "a chorus of tiny frog-like creatures trilling rhythmically in heavy tropical rain, wet, field recording"},
    {"clan": "Morthil", "seconds": 9, "prompt": "a soft breathy hooting creature at night with fluttering moth wings, distant insects, eerie jungle night ambience"},
    {"clan": "Shopra", "seconds": 4, "prompt": "a hungry bat-like creature screeching and squeaking rapidly, leathery wing flaps, close up"},
    {"clan": "Kuvel", "seconds": 12, "prompt": "a huge slow tortoise-like creature letting out a very deep low rumbling groan, stone grinding, sparse and patient"},
    {"clan": "Sesnim", "seconds": 5, "prompt": "an eel-like creature singing a gurgling bubbling whistle underwater, river flowing"},
    {"clan": "Tokrrun", "seconds": 2.5, "prompt": "a large jungle cat-like predator snarling a short aggressive growl, close and menacing"},
    {"clan": "Ulmira", "seconds": 8, "prompt": "a bright bird-like creature singing an ecstatic warbling call at sunrise, dawn chorus behind"},
    {"clan": "Velnim", "seconds": 3.5, "prompt": "a tiny baby animal mewling and chirping softly, curious and fragile, close microphone"},
    {"clan": "Lithpra", "seconds": 15, "prompt": "a gliding creature calling long airy whooshing whistles across a moonlit forest canopy, wind, crickets"},
    {"clan": "Rrunsho", "seconds": 4, "prompt": "a beetle-like creature crunching seeds rapidly with clicking mandibles, buzzing wings"},
    {"clan": "Aaruvash", "seconds": 10, "prompt": "a group of howler monkey-like creatures roaring and howling in waves, distant thunder"},
    {"clan": "Kumor", "seconds": 7, "prompt": "a mole-like burrowing creature snuffling and grunting underground, muffled digging in soil"},
    {"clan": "Nimses", "seconds": 2, "prompt": "a tiny water insect creature making quick high-pitched pips and ticks on a still pond"},
    {"clan": "Pravel", "seconds": 6, "prompt": "a courting creature making a pulsing purring trill and wing drumming, rhythmic mating display"},
    {"clan": "Eehlith", "seconds": 20, "prompt": "an ancient enormous creature making slow resonant whale-like moans echoing through a vast jungle, deep reverb"},
]

NEGATIVE = "music, melody, instruments, beat, human voice, speech, singing person, low quality, distortion, noise hiss"
STEPS = 150        # 100–200; more steps = cleaner but slower
GUIDANCE = 7.0
SEED = 498

In [17]:
os.makedirs("sounds", exist_ok=True)

def finish(x, sr, fade_s=0.03, peak=0.89):
    """Remove DC offset, fade in/out to avoid clicks, normalize."""
    x = x - x.mean(axis=0, keepdims=True)
    n = int(sr * fade_s)
    ramp = np.linspace(0.0, 1.0, n)[:, None]
    x[:n] *= ramp
    x[-n:] *= ramp[::-1]
    m = np.abs(x).max()
    return x * (peak / m) if m > 0 else x

for k, s in enumerate(SOUNDS, start=1):
    generator = torch.Generator("cuda").manual_seed(SEED + k)
    audio = pipe(
        s["prompt"],
        negative_prompt=NEGATIVE,
        num_inference_steps=STEPS,
        guidance_scale=GUIDANCE,
        audio_end_in_s=float(s["seconds"]),
        num_waveforms_per_prompt=1,
        generator=generator,
    ).audios
    x = finish(audio[0].T.float().cpu().numpy(), SR)   # (samples, channels)

    wav = f"sounds/sound_{k:02d}.wav"
    mp3 = wav.replace(".wav", ".mp3")
    sf.write(wav, x, SR)
    subprocess.run(["ffmpeg", "-y", "-loglevel", "error", "-i", wav,
                    "-codec:a", "libmp3lame", "-q:a", "3", mp3], check=True)

    print(f"{k:02d}  {s['clan']:<9} {s['seconds']:>4}s  {s['prompt'][:70]}…")
    display(Audio(x.T, rate=SR))

  0%|          | 0/150 [00:00<?, ?it/s]

/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:608: UserWarning: Should have tb<=t1 but got tb=500.00006103515625 and t1=500.0.
  warnings.warn(f"Should have {tb_name}<=t1 but got {tb_name}={tb} and t1={self._end}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.0 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:602: UserWarning: Should have tb>=t0 but got tb=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have {tb_name}>=t0 but got {tb_name}={tb} and t0={self._start}.")


01  Kithuru      3s  a small lizard-like tree creature making dry clicking croaks among rus…


  0%|          | 0/150 [00:00<?, ?it/s]

/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:608: UserWarning: Should have tb<=t1 but got tb=500.00006103515625 and t1=500.0.
  warnings.warn(f"Should have {tb_name}<=t1 but got {tb_name}={tb} and t1={self._end}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.0 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:602: UserWarning: Should have tb>=t0 but got tb=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have {tb_name}>=t0 but got {tb_name}={tb} and t0={self._start}.")


...

/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:608: UserWarning: Should have tb<=t1 but got tb=500.00006103515625 and t1=500.0.
  warnings.warn(f"Should have {tb_name}<=t1 but got {tb_name}={tb} and t1={self._end}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.0 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:602: UserWarning: Should have tb>=t0 but got tb=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have {tb_name}>=t0 but got {tb_name}={tb} and t0={self._start}.")


15  Pravel       6s  a courting creature making a pulsing purring trill and wing drumming, …


  0%|          | 0/150 [00:00<?, ?it/s]

/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:608: UserWarning: Should have tb<=t1 but got tb=500.00006103515625 and t1=500.0.
  warnings.warn(f"Should have {tb_name}<=t1 but got {tb_name}={tb} and t1={self._end}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:599: UserWarning: Should have ta>=t0 but got ta=0.0 and t0=0.3.
  warnings.warn(f"Should have ta>=t0 but got ta={ta} and t0={self._start}.")
/usr/local/lib/python3.13/dist-packages/torchsde/_brownian/brownian_interval.py:602: UserWarning: Should have tb>=t0 but got tb=0.29999998211860657 and t0=0.3.
  warnings.warn(f"Should have {tb_name}>=t0 but got {tb_name}={tb} and t0={self._start}.")


16  Eehlith     20s  an ancient enormous creature making slow resonant whale-like moans ech…


## Re-roll the ones you don't like

Change the seed (or the prompt) for a single sound and regenerate just that one. Note what you changed — it's useful for the README's "how could quality be improved" part.

In [18]:
def regenerate(k, seed=None, prompt=None):
    s = SOUNDS[k - 1]
    if prompt: s["prompt"] = prompt
    generator = torch.Generator("cuda").manual_seed(seed if seed is not None else SEED + k + 1000)
    audio = pipe(s["prompt"], negative_prompt=NEGATIVE, num_inference_steps=STEPS,
                 guidance_scale=GUIDANCE, audio_end_in_s=float(s["seconds"]),
                 generator=generator).audios
    x = finish(audio[0].T.float().cpu().numpy(), SR)
    wav = f"sounds/sound_{k:02d}.wav"
    sf.write(wav, x, SR)
    subprocess.run(["ffmpeg", "-y", "-loglevel", "error", "-i", wav,
                    "-codec:a", "libmp3lame", "-q:a", "3", wav.replace(".wav", ".mp3")], check=True)
    display(Audio(x.T, rate=SR))

# regenerate(7, seed=1234)

In [19]:
from google.colab import files

with zipfile.ZipFile("sounds.zip", "w") as z:
    for name in sorted(os.listdir("sounds")):
        if name.endswith(".mp3"):
            z.write(os.path.join("sounds", name))
files.download("sounds.zip")

<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>